# Visualising logical operations

The [Logical Assembly Visualiser](logical_assembly_visualiser.ipynb) draws a Logical Assembly
(LogASM) program as a 3D spacetime diagram. This guide is a tour of the logical operations it can
draw. Each section introduces one operation, writes a small program that uses it with the
[Logical Assembly API](../../../deltakit_compile/logical_assembly_api/guides/logical_assembly_api.ipynb),
and shows how the operation appears in the spacetime view.

The operations build on each other. The guide starts with the lifecycle of a single patch:
declaring it, preparing it, measuring its stabilisers and measuring it out. It then covers lattice
surgery between two patches with a multi-Pauli measurement, and ends with the operations that
change where a patch sits and how it is oriented: move, step and rotate, followed by grow and
shrink, which change its size.

In every diagram, the horizontal plane is the layout of the patches, in the same coordinates as
each patch's `location`, and the vertical axis is time, counted in rounds of stabiliser
measurements. A patch is drawn as a block that is as tall as the number of rounds it is kept alive
for. Its walls are coloured red and blue to tell its two kinds of boundary apart, and surfaces at
its bottom and top mark where it is prepared and where it is measured.

Every example writes its program with a `LogAsmBuilder`, uses `RotatedPlanarPatch` for its
patches, and draws it with `LogicalAssemblyVisualiser`.

In [1]:
# (c) Copyright Riverlane 2026-2026. All rights reserved.

from deltakit_compile.frontend.logasm import LogAsmBuilder, RotatedPlanarPatch

from deltakit_visualise.logical_assembly_visualiser import LogicalAssemblyVisualiser

## The lifecycle of a patch

A logical qubit is stored in a patch of surface code. The first program is the simplest one
possible, a [quantum memory](../../../deltakit_compile/logical_assembly_api/guides/quantum_memory.ipynb)
experiment: a single patch is declared, prepared, kept alive for a few rounds and measured. The
program is written one operation per cell, and drawn once it is complete.

### Declare

`declare_patch` adds a patch to the program. The patch here is a `RotatedPlanarPatch`, a rotated
planar surface code 4 data qubits wide and 4 data qubits high, so its code distance is 4.
`location=(0, 0)` puts its bottom-left corner at the origin, so it covers the square from `(0, 0)`
to `(4, 4)`, and `vertical_z=True` makes its logical `Z` operator run vertically.

Declaring a patch only reserves its qubits and does not put them in any state. In the spacetime
view, a declared patch is a grey surface at round 0.

In [2]:
builder = LogAsmBuilder()

p0 = builder.declare_patch(
    RotatedPlanarPatch(4, 4, location=(0, 0), vertical_z=True),
)

visualiser = LogicalAssemblyVisualiser(builder)
visualiser.visualise_space_time();

### Prepare

`prepare` initialises the logical qubit in an eigenstate of a Pauli basis: `"X"` prepares the
patch in the logical $|+\rangle$ state. In the spacetime view, preparing a patch colours its grey
surface according to the basis.

In [3]:
p0.prepare("X")

visualiser = LogicalAssemblyVisualiser(builder)
visualiser.visualise_space_time();

### Measure stabilisers

A logical qubit is kept alive by measuring the stabilisers of its code over and over, so that
errors can be detected and corrected. `measure_stabilisers(min_rounds=4)` asks for at least 4
rounds. Without `min_rounds`, the builder uses the smaller of the patch's width and height, which
is its code distance.

This is what gives a patch its height in the spacetime view: the walls of the block rise by one
unit per round.

In [4]:
p0.measure_stabilisers(min_rounds=4)

visualiser = LogicalAssemblyVisualiser(builder)
visualiser.visualise_space_time();

### Measure

`measure` reads the logical qubit out in the given basis, which ends the patch's life, and returns
a `Result` holding the corrected logical outcome. It caps the block with a surface at the round it
happens in.

The program is now complete. `LogicalAssemblyVisualiser` accepts the builder directly, so there is
no need to call `build_program` first, and `visualise_space_time` draws it.

In [5]:
p0.measure("X")

visualiser = LogicalAssemblyVisualiser(builder)
visualiser.visualise_space_time();

Reading the diagram from the bottom up: the patch is declared and prepared at round 0, its
stabilisers are measured for 4 rounds, and it is measured out at round 4.

## Multi-Pauli measurement

With more than one patch, logical qubits can interact. In the surface code this is done with
lattice surgery: two patches are merged through a bridge patch between them, which measures a joint
Pauli operator of the two logical qubits, and then split apart again.

`builder.multi_pauli_measure` does the merge and the split as one operation. It takes the patches
to measure, the bridges joining them and the Pauli basis to measure on each patch, so
`pauli_bases="ZZ"` measures $Z \otimes Z$ on `p0` and `p1`. The bridge here is a 4×4 patch filling
the gap between `p0`, which covers `x` from 0 to 4, and `p1`, which covers `x` from 8 to 12. You
only need to declare the bridge, as `multi_pauli_measure` prepares it and measures it out for you.
If you leave `bridges` out, the builder lays a straight bridge itself where there is only one way
to do so. The operation returns a `Result` holding the measured parity, which this example does not
use.

Both patches go through the lifecycle from the previous section, with the multi-Pauli measurement
in the middle.

In [6]:
builder = LogAsmBuilder()

p0 = builder.declare_patch(
    RotatedPlanarPatch(4, 4, location=(0, 0), vertical_z=True),
)
p1 = builder.declare_patch(
    RotatedPlanarPatch(4, 4, location=(8, 0), vertical_z=True),
)
bridge = builder.declare_patch(
    RotatedPlanarPatch(4, 4, location=(4, 0), vertical_z=True),
)

p0.prepare("X")
p1.prepare("X")

p0.measure_stabilisers(min_rounds=4)
p1.measure_stabilisers(min_rounds=4)

builder.multi_pauli_measure(operand_patches=[p0, p1], bridges=[bridge], pauli_bases="ZZ", rounds=4)

p0.measure_stabilisers(min_rounds=4)
p1.measure_stabilisers(min_rounds=4)

p0.measure("X")
p1.measure("X")

visualiser = LogicalAssemblyVisualiser(builder)
visualiser.visualise_space_time();

For the 4 rounds of the merge, the walls between `p0`, the bridge and `p1` disappear, and the three
are drawn as a single block. When the merge ends, the bridge is measured out, which splits the
patches apart again, and each one carries on for 4 more rounds before it is measured.

## Moving a patch

The remaining operations change where a patch sits on the layout, and how it is oriented. To keep
the focus on them, most of the examples from here on leave out the preparation, so their patches
start as grey surfaces.

### Move

`move` carries a patch to a new position, `offset` away from where it is. It uses the same merge
and split as a multi-Pauli measurement: the patch is merged with bridges that run from its current
position to its destination, and then split off at the far end, so the bridges have to connect the
two positions. Here `p0` moves by `(16, 12)` along an L-shaped path: `bridge_1` runs up from the
top of `p0`, and `bridge_2` runs right from the top of `bridge_1` to the destination. As with
`multi_pauli_measure`, the builder prepares the bridges and measures them out, and it tries to work
out a path itself if you don't pass any bridges.

In [7]:
builder = LogAsmBuilder()

p0 = builder.declare_patch(
    RotatedPlanarPatch(4, 4, location=(0, 0), vertical_z=True),
)
bridge_1 = builder.declare_patch(
    RotatedPlanarPatch(4, 12, location=(0, 4)),
)
bridge_2 = builder.declare_patch(
    RotatedPlanarPatch(12, 4, location=(4, 12)),
)

p0.measure_stabilisers(min_rounds=4)

p0.move((16, 12), rounds=4, bridges=[bridge_1, bridge_2])

p0.measure_stabilisers(min_rounds=4)

# visualiser = LogicalAssemblyVisualiser(builder)
# visualiser.visualise_space_time();  # Currently not supported due to missing move patch lowering

For the 4 rounds of the move, `p0`, the bridges and the destination are drawn as one L-shaped
block. Once the bridges are measured out, the patch carries on from its new position.

### Step

A move by a small offset, one that leaves the patch overlapping its old footprint, cannot be done
with bridges. `step` covers these small shifts. A rotated planar patch has its data qubits at
half-integer coordinates and its measure qubits at integer coordinates, so a step of `(0.5, 0.5)`
moves the patch diagonally onto the positions its measure qubits were in. Two steps, `(0.5, 0.5)`
then `(0.5, -0.5)`, shift it one unit to the right. Unlike a `move` by an odd offset, a step also
leaves the patch's stabilisers the same.

Here `p0` and `p1`, stacked one on top of the other, take eight steps each, zig-zagging to end up 4
units to the right of where they started.

In [9]:
builder = LogAsmBuilder()

p0 = builder.declare_patch(
    RotatedPlanarPatch(4, 4, location=(0, 0), vertical_z=True),
)
p1 = builder.declare_patch(
    RotatedPlanarPatch(4, 4, location=(0, 4), vertical_z=True),
)

p0.measure_stabilisers(min_rounds=4)
p1.measure_stabilisers(min_rounds=4)

# Each pair of steps moves a patch by (1, 0), so eight steps move it by (4, 0)
p0.step((0.5, 0.5))
p0.step((0.5, -0.5))
p1.step((0.5, 0.5))
p1.step((0.5, -0.5))
p0.step((0.5, 0.5))
p0.step((0.5, -0.5))
p0.step((0.5, 0.5))
p0.step((0.5, -0.5))
p0.step((0.5, 0.5))
p0.step((0.5, -0.5))
p1.step((0.5, 0.5))
p1.step((0.5, -0.5))
p1.step((0.5, 0.5))
p1.step((0.5, -0.5))
p1.step((0.5, 0.5))
p1.step((0.5, -0.5))

p0.measure_stabilisers(min_rounds=4)

visualiser = LogicalAssemblyVisualiser(builder)
visualiser.visualise_space_time();

Each step is drawn as one round, so the patches zig-zag across the layout one round at a time.

### Rotate

`rotate` turns a patch by 90 degrees, so that its logical `X` and `Z` operators swap between
running vertically and horizontally. The rotation also moves the patch by `offset`, which without
bridges has to be the patch's own code distance, in a direction of your choice. Here `p0` rotates
into the 4×4 region directly above it, ending up at `(0, 4)`, and `rounds` sets how many rounds the
rotation takes.

In [10]:
builder = LogAsmBuilder()

p0 = builder.declare_patch(
    RotatedPlanarPatch(4, 4, location=(0, 0), vertical_z=True),
)
p0.measure_stabilisers(min_rounds=4)
p0.rotate((0, 4), rounds=11)
p0.measure_stabilisers(min_rounds=4)
p0.measure("X")

visualiser = LogicalAssemblyVisualiser(builder)
visualiser.visualise_space_time();

While the patch rotates, the diagram covers both its old footprint and its destination. After the
rotation, the red and blue walls of the patch have swapped sides, because its boundaries are now
the other way round.

A rotation can also be given bridges. Here a 4×2 bridge sits directly above `p0`, and the patch
rotates by an offset of `(0, 2)`: it ends up covering the top half of its old footprint and the
bridge, so it needs a 4×2 strip of free space rather than a whole 4×4 region.

In [11]:
builder = LogAsmBuilder()

p0 = builder.declare_patch(
    RotatedPlanarPatch(4, 4, location=(0, 0), vertical_z=True),
)
bridge = builder.declare_patch(
    RotatedPlanarPatch(4, 2, location=(0, 4)),
)
p0.measure_stabilisers(min_rounds=4)
p0.rotate((0, 2), rounds=8, bridges=[bridge])
p0.measure_stabilisers(min_rounds=4)
p0.measure("X")

visualiser = LogicalAssemblyVisualiser(builder)
visualiser.visualise_space_time();

## Growing and shrinking a patch

`grow` and `shrink` change the size of a patch, and so its code distance, by pulling its sides
outwards or pushing them inwards by the number of units given for each side. As with the other
operations, `rounds` sets how many rounds the change takes. Here `grow(top=4, right=4)` turns a
4×4 patch into an 8×8 one with the same bottom-left corner.

In [12]:
builder = LogAsmBuilder()

p0 = builder.declare_patch(
    RotatedPlanarPatch(4, 4, location=(0, 0), vertical_z=True),
)
p0.prepare("X")
p0.measure_stabilisers(min_rounds=4)
p0.grow(top=4, right=4, rounds=4)
p0.measure("X")

visualiser = LogicalAssemblyVisualiser(builder)
visualiser.visualise_space_time();

`shrink(bottom=2, left=2)` does the reverse, trimming 2 units off the bottom and the left of a 4×4
patch to leave a 2×2 patch at `(2, 2)`.

In [13]:
builder = LogAsmBuilder()

p0 = builder.declare_patch(
    RotatedPlanarPatch(4, 4, location=(0, 0), vertical_z=True),
)
p0.measure_stabilisers(min_rounds=4)
p0.shrink(bottom=2, left=2, rounds=4)
p0.measure("X")

visualiser = LogicalAssemblyVisualiser(builder)
visualiser.visualise_space_time();

In both diagrams, the block widens or narrows at the round the patch is resized in.